# Other visulization libraries

In [2]:
import pandas as pd
import matplotlib.pyplot as plt


resultsdf = pd.read_csv('http://128.198.162.191/dataFiles/OLYMPICS/olympics_1896-2024.csv')

## Altair

A declarative visualization library based on the Vega and Vega-Lite grammar,. Instead of writing step-by-step drawing instructions, you define the links between your data columns and visual encodings (such as the x-axis, y-axis, and color), and Altair automatically handles the rendering. It is ideal for creating clean, exploratory charts with minimal code, but it is best suited for small to medium datasets because it embeds the raw data directly into the chart's output format.

In [3]:
import altair as alt

# Filter the data to only see US medals
usResults = resultsdf[resultsdf['Country'] == 'United States of America']

# Calculate counts and convert the Series to a DataFrame
medalCounts = usResults['Medal'].value_counts().reset_index()
medalCounts.columns = ['Medal', 'Count']

# Create the pie chart (using mark_arc)
chart = alt.Chart(medalCounts, title='Percent of Medals Won by the USA').mark_arc().encode(
    theta=alt.Theta(field='Count', type='quantitative'),
    color=alt.Color(
        field='Medal', 
        type='nominal',
        scale=alt.Scale(
            domain=['Gold', 'Silver', 'Bronze'],
            range=['#FFD700', '#C0C0C0', '#CD7F32']
        )
    ),
    tooltip=['Medal', 'Count'] # Adds hover interactivity
)

# Show the chart
chart.display()

alt.Chart(...)

## Plotly

A highly interactive library built on top of the plotly.js JavaScript framework,. It generates charts as interactive web elements by default, giving users native access to zoom, pan, and hover tooltips without writing any front-end code. Through its high-level API, Plotly Express, developers can quickly generate complex graphics, animated charts, 3D surface plots, and dashboards.

In [4]:
import plotly.express as px

# Filter the data to only see US medals
usResults = resultsdf[resultsdf['Country'] == 'United States of America']

# Calculate counts and convert the Series to a DataFrame
medalCounts = usResults['Medal'].value_counts().reset_index()
medalCounts.columns = ['Medal', 'Count']

# Define exact color mappings
color_map = {
    'Gold': '#FFD700', 
    'Silver': '#C0C0C0', 
    'Bronze': '#CD7F32'
}

# Create the interactive pie chart
fig = px.pie(
    medalCounts, 
    names='Medal', 
    values='Count',
    title='Percent of Medals Won by the USA',
    color='Medal',
    color_discrete_map=color_map
)

# Show the chart
fig.show()

## Pydeck

A specialized geospatial library powered by the deck.gl framework and WebGL. PyDeck focuses almost entirely on immersive, large-scale 3D mapping. It allows developers to quickly aggregate and render massive spatial datasets—such as extruded 3D hex bins, point clouds, and geographic heatmaps—directly over base maps like Mapbox or OpenStreetMap with cinematic camera controls.

In [1]:
import pydeck as pdk
import pandas as pd

# 1. Load the dataset (UK traffic accidents)
UK_ACCIDENTS_DATA = (
    "https://raw.githubusercontent.com/visgl/deck.gl-data/master/"
    "examples/3d-heatmap/heatmap-data.csv"
)
df = pd.read_csv(UK_ACCIDENTS_DATA)

# 2. Configure the 3D Hexagon Layer
layer = pdk.Layer(
    "HexagonLayer",
    data=df,
    get_position=["lng", "lat"],
    auto_highlight=True,       # Highlights the hexagon when hovered
    elevation_scale=50,        # Multiplier for the height of the 3D columns
    pickable=True,             # Enables tooltips and click events
    elevation_range=[0, 3000], # Range of the extrusion heights
    extruded=True,             # Renders in 3D instead of flat 2D
    coverage=1                 # Radius of the hexagon cell (0 to 1)
)

# 3. Define the initial camera angle and map location
view_state = pdk.ViewState(
    longitude=-1.415,
    latitude=52.2323,
    zoom=6,
    min_zoom=5,
    max_zoom=15,
    pitch=40.5,                # Tilts the camera for a 3D perspective
    bearing=-27.36             # Rotates the map
)

# 4. Build the final Deck object and add a tooltip
r = pdk.Deck(
    layers=[layer],
    initial_view_state=view_state,
    tooltip={"text": "Accidents in this area: {elevationValue}"}
)

# 5. Export to a local HTML file
r.to_html("uk_accidents_3d.html")